In [1]:
import numpy as np
import pandas as pd

In [2]:
df=pd.read_csv('fake_news_dataset.csv')
df.head()

,title,text,date,source,author,category,label
0,Foreign Democrat final.,more tax development both store agreement lawy...,2023-03-10,NY Times,Paula George,Politics,real
1,To offer down resource great point.,probably guess western behind likely next inve...,2022-05-25,Fox News,Joseph Hill,Politics,fake
2,Himself church myself carry.,them identify forward present success risk sev...,2022-09-01,CNN,Julia Robinson,Business,fake
3,You unit its should.,phone which item yard Republican safe where po...,2023-02-07,Reuters,Mr. David Foster DDS,Science,fake
4,Billion believe employee summer how.,wonder myself fact difficult course forget exa...,2023-04-03,CNN,Austin Walker,Technology,fake


In [3]:
df.shape

(20000, 7)

In [4]:
df=df.drop(columns=['date', 'source', 'category'])

In [5]:
df.sample(10)

,title,text,author,label
17481,Fast work movie sea instead rule.,oil others religious example reflect civil met...,Richard Bennett,real
15803,Maybe list blue.,career cultural federal company in base profes...,Jacqueline Liu,fake
8652,Fast ever that policy structure.,near benefit impact laugh great score staff si...,Damon Chandler,real
5589,Two bank third activity chair.,high still set management try treat best low w...,Alexis Moore,fake
8456,Do past grow present even rate rule.,thus town fund dream technology whose town rac...,Linda Goodman,fake
12098,Boy cell foot capital career.,follow pay performance less structure appear m...,Dalton Price,real
18124,Account seek often key country west card eight.,note perform reflect answer investment attenti...,Courtney Wilson,real
14904,New image fly.,ago all should trade town drug fact south unit...,Allison Gaines,real
4205,Stand sit guy sport.,hot tonight own movie natural daughter most ex...,Traci Brown,fake
7313,Common rich eat detail involve.,his key born positive even garden our three tr...,Corey Medina,fake


In [6]:
df['label'] = df['label'].map({'real': 1, 'fake': 0})
df.head()

,title,text,author,label
0,Foreign Democrat final.,more tax development both store agreement lawy...,Paula George,1
1,To offer down resource great point.,probably guess western behind likely next inve...,Joseph Hill,0
2,Himself church myself carry.,them identify forward present success risk sev...,Julia Robinson,0
3,You unit its should.,phone which item yard Republican safe where po...,Mr. David Foster DDS,0
4,Billion believe employee summer how.,wonder myself fact difficult course forget exa...,Austin Walker,0


In [7]:
df.isnull().sum()

title        0
text         0
author    1000
label        0
dtype: int64

In [8]:
df=df.dropna()

In [9]:
df.isnull().sum()

title     0
text      0
author    0
label     0
dtype: int64

In [10]:
df.shape

(19000, 4)

In [11]:
X=df.drop('label', axis=1)

In [12]:
y=df['label']

In [13]:
print(X.shape)
print(y.shape)

(19000, 3)
(19000,)


In [14]:
y.value_counts()

label
0    9571
1    9429
Name: count, dtype: int64

In [ ]:
import tensorflow as tf

In [16]:
from tensorflow.keras.models import Sequential
from tensorflow.keras.layers import Embedding
from tensorflow.keras.preprocessing.sequence import pad_sequences
from tensorflow.keras.preprocessing.text import one_hot
from tensorflow.keras.layers import LSTM
from tensorflow.keras.layers import Bidirectional
from tensorflow.keras.layers import Dense

In [17]:
voc_size=10000

In [18]:
messages= X.copy()
messages = messages.reset_index(drop=True)

In [19]:
messages['full_content'] = messages['title'] + " " + messages['text']

In [20]:
import nltk
import re
from nltk.corpus import stopwords

In [21]:
nltk.download('stopwords')

[nltk_data] Downloading package stopwords to
[nltk_data]     C:\Users\ratna\AppData\Roaming\nltk_data...
[nltk_data]   Package stopwords is already up-to-date!


True

In [22]:
from nltk.stem.porter import PorterStemmer
ps=PorterStemmer()

In [23]:
# df.head(20)
messages.head()

,title,text,author,full_content
0,Foreign Democrat final.,more tax development both store agreement lawy...,Paula George,Foreign Democrat final. more tax development b...
1,To offer down resource great point.,probably guess western behind likely next inve...,Joseph Hill,To offer down resource great point. probably g...
2,Himself church myself carry.,them identify forward present success risk sev...,Julia Robinson,Himself church myself carry. them identify for...
3,You unit its should.,phone which item yard Republican safe where po...,Mr. David Foster DDS,You unit its should. phone which item yard Rep...
4,Billion believe employee summer how.,wonder myself fact difficult course forget exa...,Austin Walker,Billion believe employee summer how. wonder my...


In [24]:
corpus=[]
for i in range(0, len(messages)):
    review = re.sub('[^a-zA-Z]'," ", str(messages['full_content'][i]))
    review=review.lower()
    review=review.split()
    review=[ps.stem(word) for word in review if not word in stopwords.words('english')]
    review=" ".join(review)
    corpus.append(review)

In [25]:
onehot_rep=[one_hot(words, voc_size) for words in corpus]
print(onehot_rep)

[[7576, 3484, 2536, 4836, 1451, 6256, 3697, 8090, 8979, 2914, 7469, 7644, 2275, 5423, 5216, 3386, 8017, 4086, 7178, 3678, 2409, 9922, 4462, 1979, 1871, 1528, 2327, 4549, 7006, 8464, 8831, 8641, 3386, 5526, 4764, 1552, 5144, 5111, 9282, 1951, 9556, 349, 9827, 6576, 6415, 6675, 4627, 1266, 3123, 1964, 6844, 4019, 7625, 438, 6298, 6843, 420, 8051, 9891, 7372, 7510, 2185, 3839, 4819, 3698, 9337, 4255, 4867, 9532, 8935, 5111, 5111, 6442, 6891, 3224, 5076, 4417, 2156, 1451, 7367, 4878, 7714, 6891, 2557, 4641, 3690, 7906, 2988, 3404, 9578, 9774, 6797, 7856, 438, 1451, 3235, 7377, 1376, 8633, 2324, 9556, 2428, 3230, 8017, 5103, 614, 8015, 6256, 7550, 1595, 9774, 4790, 6233, 9998, 1280, 7457, 9675, 7856, 6555, 4376, 4588, 9774, 2409, 7267, 2312, 3542, 1595, 1196, 5767, 5553, 2121, 1951, 8632, 4305, 1452, 451, 5884, 9510, 5884, 7787, 9915, 6024, 6476, 9532, 2252, 5111, 4958, 23, 2841, 4484, 344, 18, 4588, 8911, 2438, 2391, 9675, 8363, 7423, 7457, 6785, 6298, 8367, 9174, 9001, 4346, 7714, 9678, 9

# Embedding representation

In [26]:
max_words = messages['full_content'].dropna().str.split().str.len().max()
print(f"The longest sentence has {max_words} words.")

The longest sentence has 308 words.


In [27]:
sent_len = 120
embedded_docs=pad_sequences(onehot_rep, padding='pre', maxlen=sent_len)

In [28]:
embedded_docs[0]

array([5076, 4417, 2156, 1451, 7367, 4878, 7714, 6891, 2557, 4641, 3690,
       7906, 2988, 3404, 9578, 9774, 6797, 7856,  438, 1451, 3235, 7377,
       1376, 8633, 2324, 9556, 2428, 3230, 8017, 5103,  614, 8015, 6256,
       7550, 1595, 9774, 4790, 6233, 9998, 1280, 7457, 9675, 7856, 6555,
       4376, 4588, 9774, 2409, 7267, 2312, 3542, 1595, 1196, 5767, 5553,
       2121, 1951, 8632, 4305, 1452,  451, 5884, 9510, 5884, 7787, 9915,
       6024, 6476, 9532, 2252, 5111, 4958,   23, 2841, 4484,  344,   18,
       4588, 8911, 2438, 2391, 9675, 8363, 7423, 7457, 6785, 6298, 8367,
       9174, 9001, 4346, 7714, 9678, 9247, 2893, 1518, 2756, 8017, 8979,
       6389, 7312, 9044, 3375, 2707, 4232, 3879, 9603, 8911, 3689, 7450,
       7478, 9915, 9704, 5928, 1025, 7776, 5951, 3839, 4654, 8028],
      dtype=int32)

In [29]:
from tensorflow.keras.preprocessing.text import Tokenizer
from tensorflow.keras.preprocessing.sequence import pad_sequences

# Initialize and fit tokenizer
tokenizer = Tokenizer(num_words=10000, oov_token="<OOV>")
tokenizer.fit_on_texts(corpus)

# Convert text to clean sequences
X_sequences = tokenizer.texts_to_sequences(corpus)

# Pad sequences properly
X_padded = pad_sequences(X_sequences, maxlen=150, padding='pre', truncating='pre')

In [30]:
# embedding_vect_features=200
# model=Sequential()
# model.add(Embedding(voc_size,embedding_vect_features,input_length=sent_len))
# model.add(Bidirectional(LSTM(100)))
# model.add(Dense(1, activation='sigmoid'))
# model.compile(loss='binary_crossentropy', optimizer='adam',metrics=['accuracy'])
# print(model.summary())

from tensorflow.keras.layers import SpatialDropout1D, Dropout

model = Sequential([
    Embedding(voc_size, 128, input_length=150),
    SpatialDropout1D(0.2), # Drops entire 1D feature maps to prevent embedding overfitting
    Bidirectional(LSTM(64, dropout=0.2, recurrent_dropout=0.2)), # Internal LSTM dropout
    Dense(32, activation='relu'),
    Dropout(0.3),
    Dense(1, activation='sigmoid') # Binary classification output
])

model.compile(loss='binary_crossentropy', optimizer='adam', metrics=['accuracy'])


c:\Users\ratna\anaconda3\Lib\site-packages\keras\src\layers\core\embedding.py:123: UserWarning: Argument `input_length` is deprecated. Just remove it.
  warnings.warn(


In [40]:
X_final=np.array(X_padded)
y_final=np.array(y)

In [41]:
from sklearn.model_selection import train_test_split
X_train, X_test,y_train,y_test=train_test_split(X_final,y_final, test_size=0.33, random_state=42)

In [42]:
import tensorflow as tf
earlystops = tf.keras.callbacks.EarlyStopping(
    monitor='val_loss',
    min_delta=0.001,
    patience=20,
    verbose=1,
    mode='auto',
    baseline=None,
    restore_best_weights=True,
    start_from_epoch=0
)

In [43]:
model.fit(X_train, y_train, validation_data=(X_test, y_test), epochs=1000, batch_size=32, callbacks=earlystops)

Epoch 1/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 45s 106ms/step - accuracy: 0.4947 - loss: 0.7098 - val_accuracy: 0.4914 - val_loss: 0.6949
Epoch 2/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 40s 101ms/step - accuracy: 0.5067 - loss: 0.6925 - val_accuracy: 0.4952 - val_loss: 0.6951
Epoch 3/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 38s 95ms/step - accuracy: 0.5332 - loss: 0.6881 - val_accuracy: 0.4984 - val_loss: 0.6945
Epoch 4/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 38s 95ms/step - accuracy: 0.5666 - loss: 0.6681 - val_accuracy: 0.4904 - val_loss: 0.7043
Epoch 5/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 38s 96ms/step - accuracy: 0.6100 - loss: 0.6364 - val_accuracy: 0.4888 - val_loss: 0.7351
Epoch 6/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 40s 101ms/step - accuracy: 0.6537 - loss: 0.5983 - val_accuracy: 0.5002 - val_loss: 0.7837
Epoch 7/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 38s 95ms/step - accuracy: 0.6894 - loss: 0.5572 - val_accuracy: 0.5022 - val_loss: 0.8232
Epoch 8/1000
398/398 ━━━━━━━━━━━━━━━━━━━━ 38s 96ms/step - accuracy: 0.725

In [44]:
y_pred_raw = model.predict(X_test)

196/196 ━━━━━━━━━━━━━━━━━━━━ 4s 16ms/step


In [45]:
y_pred = (y_pred_raw >= 0.5).astype(int).flatten()

In [46]:
from sklearn.metrics import confusion_matrix, accuracy_score

In [47]:
confusion_matrix(y_test,y_pred)

array([[  10, 3174],
       [  15, 3071]])

In [48]:
print(accuracy_score(y_test,y_pred))

0.49138755980861243
